# 12 -- Buy land: dedicate 2 extra hands to NE

Follow-up to `notebooks/11_buy_land_ne.ipynb`, which relocated hands
3/4 from NW to NE and lost 20/20 to `melon_then_wheat_agent` (economic,
not a bug -- land was only affordable ~day 12, too few days left to
repay the $1000 cost from 2 hands' worth of WHEAT). This time: since
hiring has no hard cap in the engine, hire 2 *extra* hands (indices 5
and 6) dedicated to NE instead of relocating hands away from NW, so NW
coverage never drops.

Plan (see design discussion in chat):
1. Confirm empirically where a newly-hired hand spawns once NE is
   already unlocked -- still one of the original 4 NW corners, or a
   5th NE corner too? Determines whether hands 5/6 need the NW
   `SPAWN_FEEDER` merged in as well as the NE one.
2. Reuse/adapt the NE loop and zone geometry from notebook 11
   (`LOOP_ORDER_HANDS_NE`, `SPAWN_FEEDER_NE`, `ZONE_3_NE`/`ZONE_4_NE`).
3. Build the new agent: hands 0-4 unchanged from `melon_then_wheat_agent`
   (NW, `HAND_ZONES`, melon-then-wheat by day); hire cap rises from 5 to
   7 once `"NE" in unlocked_quadrants`; hands 5/6 routed to NE, always
   tending WHEAT.
4. Validate against the current best, `melon_then_wheat_agent`, via
   `evaluate.py`, n=20, at least twice.

In [13]:
import sys
from pathlib import Path

from kaggle_environments import make

sys.path.insert(0, str(Path.cwd().parent / "src"))

from kaggriculture_bot.evaluate import evaluate
from kaggriculture_bot.strategies.baseline import (
    DIRECTIONS,
    HAND_ZONES,
    LOOP_ORDER_12,
    LOOP_ORDER_HANDS,
    SPAWN_FEEDER,
    melon_then_wheat_agent,
)

## Mini-test: where does a new hand spawn once NE is already unlocked?

A throwaway agent, same idea as notebook 11's `_test_buy_land_agent`: buy
NE as soon as affordable, then keep hiring past 5 so you get at least one
hand hired *after* `unlocked_quadrants` already contains `"NE"`. Inspect
that hand's position the turn it appears.

In [14]:
def _test_buy_land_agent(obs):
      market = []
      farm = obs["farms"][obs["player"]]
      if farm["money"] >= 1000 and len(farm["unlocked_quadrants"]) == 1:
          market.append(["BUY_LAND"])
      if len(obs["farms"][obs["player"]]["hands"]) < 7:
          market.append(["HIRE"])
      print(
                "day", obs["day"],
                "observation:", obs["farms"][obs["player"]]["hands"],
                )
      return {"farmer": ["PASS"], "hands": [], "market": market}

test_env = make("kaggriculture", configuration={"episodeSteps": 720}, debug=True)
test_env.run([_test_buy_land_agent, "random"])

day 0 observation: []
day 0 observation: [[5, 4]]
day 0 observation: [[5, 4], [4, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 observation: [[5, 4], [4, 5], [5, 5], [4, 4], [5, 4], [4, 5], [5, 5]]
day 0 

[[{'action': {'farmer': ['PASS'], 'hands': [], 'market': []},
   'reward': 0,
   'info': {},
   'observation': {'remainingOverageTime': 60,
    'step': 0,
    'player': 0,
    'farms': [{'money': 3000.0,
      'tiles': [[None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
 

## NE loop and zones for hands 5/6

Reuse notebook 11's `LOOP_ORDER_HANDS_NE`/`SPAWN_FEEDER_NE`/`ZONE_3_NE`/
`ZONE_4_NE` (rename if it reads better with indices 5/6 instead of 3/4),
plus the mini-test finding above -- merge in the NW `SPAWN_FEEDER` too
only if that mini-test shows it's needed.

In [15]:
LOOP_ORDER_HANDS_NE = {
    (5, 4): (6, 4), (6, 4): (7, 4), (7, 4): (8, 4), (8, 4): (9, 4),
    (9, 4): (9, 3), (9, 3): (9, 2), (9, 2): (9, 1), (9, 1): (9, 0),
    (9, 0): (8, 0), (8, 0): (7, 0), (7, 0): (6, 0), (6, 0): (5, 0),
    (5, 0): (5, 1), (5, 1): (5, 2), (5, 2): (5, 3), (5, 3): (5, 4),
}
ZONE_TOP_NE = {
    (5, 0): (6, 0), (6, 0): (7, 0), (7, 0): (8, 0), (8, 0): (9, 0),
    (9, 0): (9, 1), (9, 1): (8, 1), (8, 1): (7, 1), (7, 1): (6, 1),
    (6, 1): (5, 1), (5, 1): (5, 0),
}
ZONE_BOTTOM_NE = {
    (6, 2): (5, 2), (5, 2): (5, 3), (5, 3): (5, 4), (5, 4): (6, 4),
    (6, 4): (7, 4), (7, 4): (8, 4), (8, 4): (9, 4), (9, 4): (9, 3),
    (9, 3): (9, 2), (9, 2): (8, 2), (8, 2): (7, 2), (7, 2): (7, 3),
    (7, 3): (6, 3), (6, 3): (6, 2),
}
SPAWN_FEEDER_NE = {(4, 4): (5, 4), (4, 5): (4, 4), (5, 5): (5, 4)}

## Sanity check: still valid closed cycles

Same `assert_is_closed_adjacent_cycle` check used in every prior
notebook for a new loop/zone.

In [16]:
def assert_is_closed_adjacent_cycle(loop_order):
    n = len(loop_order)
    start = next(iter(loop_order))
    pos = start
    visited = set()
    for _ in range(n):
        visited.add(pos)
        (x, y), (nx, ny) = pos, loop_order[pos]
        assert abs(nx - x) + abs(ny - y) == 1
        pos = (nx, ny)
    assert pos == start
    assert visited == set(loop_order)


assert_is_closed_adjacent_cycle(LOOP_ORDER_HANDS_NE)
print("LOOP_ORDER_HANDS_NE: valid closed cycle,", len(LOOP_ORDER_HANDS_NE), "tiles")
assert_is_closed_adjacent_cycle(ZONE_TOP_NE)
print("ZONE_TOP_NE: valid closed cycle,", len(ZONE_TOP_NE), "tiles")
assert_is_closed_adjacent_cycle(ZONE_BOTTOM_NE)
print("ZONE_BOTTOM_NE: valid closed cycle,", len(ZONE_BOTTOM_NE), "tiles")
assert not (set(ZONE_TOP_NE) & set(ZONE_BOTTOM_NE))
print("ZONE_TOP_NE / ZONE_BOTTOM_NE: disjoint")
for pos, nxt in SPAWN_FEEDER_NE.items():
    assert abs(nxt[0] - pos[0]) + abs(nxt[1] - pos[1]) == 1
    assert nxt == (5, 4) or nxt in SPAWN_FEEDER_NE
print("SPAWN_FEEDER_NE: valid, all one step closer to (5,4)")

LOOP_ORDER_HANDS_NE: valid closed cycle, 16 tiles
ZONE_TOP_NE: valid closed cycle, 10 tiles
ZONE_BOTTOM_NE: valid closed cycle, 14 tiles
ZONE_TOP_NE / ZONE_BOTTOM_NE: disjoint
SPAWN_FEEDER_NE: valid, all one step closer to (5,4)


## Building the extra-hands agent

Start from `melon_then_wheat_agent`'s body. Changes:
1. Hire cap: `5` normally, `7` once `"NE" in unlocked_quadrants`.
2. Hands 0-4: unchanged.
3. Hands 5/6: NE loop/zone from above, always plant/tend `WHEAT`.
4. Everything else (farmer, `BUY_LAND` trigger, selling) unchanged.

In [17]:
def melon_then_wheat_agent_v2(obs):
    
    crop_to_plant = "MELON" if obs["day"] < 10 else "WHEAT"
    crop_seeds = obs["private"]["seeds"].get(crop_to_plant, 0)

    market = []
    hands = []

    for i, (hx, hy) in enumerate(obs["farms"][obs["player"]]["hands"]):
        if i in (5, 6):
            own_zone = ZONE_TOP_NE if i == 5 else ZONE_BOTTOM_NE
            hand_loop = {
                **LOOP_ORDER_HANDS_NE, **SPAWN_FEEDER_NE,
                **own_zone,
                }
        else:
            own_zone = HAND_ZONES[i % len(HAND_ZONES)]
            hand_loop = {**LOOP_ORDER_HANDS, **SPAWN_FEEDER, **own_zone}

        target_x, target_y = hand_loop[(hx, hy)]
        if (target_x, target_y) == (hx, hy):
            move = ["PASS"]
        else:
            move = [DIRECTIONS[(target_x - hx, target_y - hy)]]

        hand_tile = obs["farms"][obs["player"]]["tiles"][hy][hx]
        in_own_zone = (hx, hy) in own_zone
        if hand_tile == "LOCKED" or not in_own_zone:
            op = move
        elif hand_tile is None and crop_seeds > 0:
            op = ["PLANT", crop_to_plant]
        elif hand_tile is not None and hand_tile.get("kind") == "PLANT":
            crop_age = obs["day"] - hand_tile["planted_day"]
            threshold = 10 if hand_tile["crop"] == "MELON" else 2
            if crop_age >= threshold:
                op = ["HARVEST"]
            elif not hand_tile.get("watered_today"):
                op = ["WATER"]
            else:
                op = move
        else:
            op = move
        hands.append(op)

    if len(obs["farms"][obs["player"]]["hands"]) < 5:
        market.append(["HIRE"])
    elif len(obs["farms"][obs["player"]]["unlocked_quadrants"]) > 1 and len(obs["farms"][obs["player"]]["hands"]) < 7:
        market.append(["HIRE"])

    if obs["step"] == 0 or crop_seeds <= 5:
        market.append(["BUY_SEED", crop_to_plant, 8 - crop_seeds])

    if obs["farms"][obs["player"]]["money"] >= 1000 and len(obs["farms"][obs["player"]]["unlocked_quadrants"]) == 1 and crop_to_plant == "WHEAT":
        market.append(["BUY_LAND"])
              
    farmer_pos = obs["farms"][obs["player"]]["farmer"]
    x, y = farmer_pos
    target_x, target_y = LOOP_ORDER_12[(x, y)]
    direction = DIRECTIONS[(target_x - x, target_y - y)]

    tile = obs["farms"][obs["player"]]["tiles"][y][x]

    wheat_in_shed = obs["private"]["shed"].get("WHEAT", 0)
    melon_in_shed = obs["private"]["shed"].get("MELON", 0)
    if wheat_in_shed > 0:
        market.append(["SELL", "WHEAT", wheat_in_shed])
    if melon_in_shed > 0:
        market.append(["SELL", "MELON", melon_in_shed])

    if tile is None and crop_seeds > 0:
        farmer = ["PLANT", crop_to_plant]
    elif tile is not None and tile.get("kind") == "PLANT":
        crop_age = obs["day"] - tile["planted_day"]
        threshold = 10 if tile["crop"] == "MELON" else 2
        if crop_age >= threshold:
            farmer = ["HARVEST"]
        elif not tile.get("watered_today"):
            farmer = ["WATER"]
        else:
            farmer = [direction]
    else:
        farmer = [direction]

    return {"farmer": farmer, "hands": hands, "market": market}

## Validate against the current best

Current best is `melon_then_wheat_agent`. Run twice, independently.

In [18]:
print(evaluate(melon_then_wheat_agent, melon_then_wheat_agent_v2, n=20))

{'win_rate': 0.0, 'avg_money': 14569.0}


In [19]:
print(evaluate(melon_then_wheat_agent, melon_then_wheat_agent_v2, n=20))

{'win_rate': 0.0, 'avg_money': 14403.0}
